# Daylight Envelopes

USC supports two approaches to daylight access — one purely geometric, one climate-weighted.

### Approach 1: Tilted Plane (geometric)

A fixed angular plane sweeps around the test surfaces and carves away any volume that violates a target height-to-width ratio. This is the **daylight envelope** (see Brown & DeKay's *Sun, Wind & Light* 2nd ed. 2014).

You specify an angle in degrees from horizontal: **45° means a 1:1 height-to-width ratio** — for every metre of building height, there must be one metre of setback from the test surface. You can also specify different angles per orientation octant starting from North and proceeding clockwise (Northeast --> East --> Southeast etc)



### Approach 2: CIE Overcast Sky (climatic)

Sky patches are weighted by the **CIE Standard Overcast Sky** luminance distribution:

$$L(\theta) = L_z \cdot \frac{1 + 2\cos\theta}{3}$$

In plain language: **the zenith is 3× brighter than the horizon** under overcast conditions. Voxels blocking high-altitude sky get higher penalty scores than those blocking the horizon. This produces a climate-weighted daylight envelope that reflects how diffuse light actually reaches street level.

This notebook demonstrates both approaches, plus a **per-octant** variant of the geometric method.


## Imports and Setup

In [1]:
from pathlib import Path
from urbansolarcarver import user_config, run_pipeline
import trimesh

REPO_ROOT = Path.cwd().parent
print(f"Repository root: {REPO_ROOT}")


Warp 1.8.1 initialized:
   CUDA Toolkit 12.8, Driver 12.6
   Devices:
     "cpu"      : "AMD64 Family 23 Model 113 Stepping 0, AuthenticAMD"
     "cuda:0"   : "NVIDIA GeForce RTX 3060" (12 GiB, sm_86, mempool enabled)
   Kernel cache:
     C:\Users\arisv\AppData\Local\NVIDIA\warp\Cache\1.8.1
Repository root: d:\RESEARCH_CENTER\ACTIVE_PROJECTS\RSBenvelope_generation\urbanSolarCarver


## 2. Input geometry

We use the **new building** scenario: a proposed building volume being carved to protect daylight access to neighbouring windows.

In [2]:
max_volume_path = REPO_ROOT / "examples" / "test_inputs" / "full_blocks" / "maxVolume.ply"
test_surface_path = REPO_ROOT / "examples" / "test_inputs" / "full_blocks" / "testSurfaces.ply"

# Load and inspect
max_vol = trimesh.load(str(max_volume_path))
test_srf = trimesh.load(str(test_surface_path))

max_vol.visual.face_colors = [200, 200, 200, 255]
test_srf.visual.face_colors = [0, 200, 0, 255]
trimesh.Scene([max_vol, test_srf]).show()


---

## A. Tilted Plane

The tilted-plane method enforces a maximum building height relative to distance from the test surfaces. The key parameter is `tilted_plane_angle_deg`:

| Angle | H:W Ratio | Effect |
|-------|-----------|--------|
| 30° | 0.58:1 | Very conservative |
| 45° | 1:1 | Balanced |
| 60° | 1.73:1 | Permissive |

In [3]:
out_dir = REPO_ROOT / "examples" / "test_outputs" / "daylight_demo"

cfg_plane = user_config(
max_volume_path   = str(max_volume_path),
test_surface_path = str(test_surface_path),
out_dir           = str(out_dir / "tilted_plane"),

mode = "tilted_plane",

tilted_plane_angle_deg = 45.0,  # 45° = 1:1 height-to-width ratio

voxel_size = 1.0,
grid_step  = 1.0,
)

print(f"Mode  : {cfg_plane.mode}")
print(f"Angle : {cfg_plane.tilted_plane_angle_deg}°")
print(f"Voxel : {cfg_plane.voxel_size} m")


Mode  : tilted_plane
Angle : 45.0°
Voxel : 1.0 m


In [4]:
result_plane = run_pipeline(cfg_plane, cfg_plane.out_dir)

print(f"Volume retained: {result_plane.exporting.retention_pct:.1f}%")
print(f"Faces:           {result_plane.exporting.faces:,}")

Module urbansolarcarver.raytracer 5dd8826 load on device 'cuda:0' took 1.13 ms  (cached)


D:\RESEARCH_CENTER\ACTIVE_PROJECTS\RSBenvelope_generation\urbanSolarCarver\src\urbansolarcarver\raytracer.py:728: UserWarning: DDA buffer overflow (6977483 > 1928820), retrying with 40/ray
  return _trace_dda_warp(
D:\RESEARCH_CENTER\ACTIVE_PROJECTS\RSBenvelope_generation\urbanSolarCarver\src\urbansolarcarver\raytracer.py:728: UserWarning: DDA buffer overflow (6977483 > 3857640), retrying with 80/ray
  return _trace_dda_warp(


Volume retained: 35.0%
Faces:           103,900


In [5]:
envelope_plane = trimesh.load(result_plane.exporting.export_path)
envelope_plane.visual.face_colors = [70, 130, 180, 255]  # steel blue
trimesh.Scene([envelope_plane]).show()

---

## B. Per-Octant Angles

Instead of one uniform angle, you can specify **eight values** — one for each compass octant, in clockwise order starting from north: `[N, NE, E, SE, S, SW, W, NW]`.

### Why asymmetric angles?

In the **northern hemisphere**, the south side of a street canyon receives the most direct sunlight. You can use a **shallower angle** (more aggressive carving) on the south side, and a **steeper angle** (more permissive, taller buildings) on the north where the daylight impact is smaller. Angles per street canyon are also much easier to implement as an urban design code / local planning regulation than more complex geometries.


In [6]:
#                  N   NE   E   SE   S   SW   W   NW
octant_angles = [45,  40,  35,  30,  25,  30,  35,  40]

cfg_octant = user_config(
    max_volume_path   = str(max_volume_path),
    test_surface_path = str(test_surface_path),
    out_dir           = str(out_dir / "tilted_plane_octant"),

    mode = "tilted_plane",

    tilted_plane_angle_deg = octant_angles,

    voxel_size = 1.0,
    grid_step  = 1.0,
)

print(f"Mode   : {cfg_octant.mode}")
print(f"Angles : {cfg_octant.tilted_plane_angle_deg}")


Mode   : tilted_plane
Angles : [45.0, 40.0, 35.0, 30.0, 25.0, 30.0, 35.0, 40.0]


In [7]:
result_octant = run_pipeline(cfg_octant, cfg_octant.out_dir)

print(f"Volume retained: {result_octant.exporting.retention_pct:.1f}%")
print(f"Faces:           {result_octant.exporting.faces:,}")

D:\RESEARCH_CENTER\ACTIVE_PROJECTS\RSBenvelope_generation\urbanSolarCarver\src\urbansolarcarver\raytracer.py:728: UserWarning: DDA buffer overflow (7439602 > 1928820), retrying with 40/ray
  return _trace_dda_warp(
D:\RESEARCH_CENTER\ACTIVE_PROJECTS\RSBenvelope_generation\urbanSolarCarver\src\urbansolarcarver\raytracer.py:728: UserWarning: DDA buffer overflow (7439602 > 3857640), retrying with 80/ray
  return _trace_dda_warp(


Volume retained: 21.0%
Faces:           77,736


In [8]:
envelope_oct = trimesh.load(result_octant.exporting.export_path)
envelope_oct.visual.face_colors = [180, 100, 50, 255]  # orange-brown
trimesh.Scene([envelope_oct]).show()


---

## C. CIE Overcast Daylight

The `daylight` mode uses actual ray casting to score each voxel by how much sky luminance it blocks from reaching the test surfaces.

### The model in plain language

Under an overcast sky the zenith is **3× brighter** than the horizon. So:
- A voxel blocking sky near the **zenith** → **high** penalty
- A voxel blocking sky near the **horizon** → **low** penalty
- `carve_fraction` then decides how much total penalty to tolerate

The `daylight` mode does **not** need a weather file or an analysis period — it uses a fixed theoretical sky model.


In [9]:
cfg_daylight = user_config(
    max_volume_path   = str(max_volume_path),
    test_surface_path = str(test_surface_path),
    out_dir           = str(out_dir / "daylight_cie"),

    mode = "daylight",

    voxel_size = 1.0,
    grid_step  = 1.0,
)

print(f"Mode  : {cfg_daylight.mode}")
print(f"Voxel : {cfg_daylight.voxel_size} m")


Mode  : daylight
Voxel : 1.0 m


In [10]:
# This one does actual ray casting — slower than tilted_plane
result_daylight = run_pipeline(cfg_daylight, cfg_daylight.out_dir)

print(f"Volume retained: {result_daylight.exporting.retention_pct:.1f}%")
print(f"Faces:           {result_daylight.exporting.faces:,}")


Volume retained: 46.0%
Faces:           110,516


In [11]:
envelope_dl = trimesh.load(result_daylight.exporting.export_path)
envelope_dl.visual.face_colors = [180, 50, 180, 255]  # purple
trimesh.Scene([envelope_dl]).show()


---

## C. CIE Overcast Daylight

The `daylight` mode uses the CIE Standard Overcast Sky luminance distribution to
weight sky patches. Instead of a fixed geometric angle, each voxel is scored by how much
sky luminance it blocks from reaching the test surfaces.

Under a uniformly overcast sky, the zenith (directly overhead) is brighter
than the horizon. The brightness varies smoothly between these extremes following a cosine
curve. This means:

- A voxel that blocks sky near the **zenith** gets a high penalty score.
- A voxel that blocks sky near the **horizon** gets a low penalty score.
- The thresholding step then decides how much total penalty to tolerate.

In [12]:
cfg_daylight = user_config(
    max_volume_path   = str(max_volume_path),
    test_surface_path = str(test_surface_path),
    out_dir           = str(out_dir / "daylight_cie"),

    mode = "daylight",

    voxel_size     = 1.0,
    grid_step      = 1.0,
    carve_fraction = 0.9,  # remove voxels to preserve 90% of available daylight 
)

print(f"Mode           : {cfg_daylight.mode}")
print(f"Voxel          : {cfg_daylight.voxel_size} m")
print(f"Carve fraction : {cfg_daylight.carve_fraction}")


Mode           : daylight
Voxel          : 1.0 m
Carve fraction : 0.9


In [13]:
# This one does actual ray casting — slower than tilted_plane
result_daylight = run_pipeline(cfg_daylight, cfg_daylight.out_dir)

print(f"Volume retained: {result_daylight.exporting.retention_pct:.1f}%")
print(f"Faces:           {result_daylight.exporting.faces:,}")


Volume retained: 31.3%
Faces:           93,844


In [14]:
envelope_dl = trimesh.load(result_daylight.exporting.export_path)
envelope_dl.visual.face_colors = [180, 50, 180, 255]  # purple
trimesh.Scene([envelope_dl]).show()


### Run report

The run report summarises the configuration, scoring, thresholding decisions, and mesh statistics for the CIE daylight run.


In [15]:
from IPython.display import Markdown, display

report_path = Path(cfg_daylight.out_dir) / "run_report.md"
if report_path.is_file():
    display(Markdown(report_path.read_text(encoding="utf-8")))
else:
    print(f"Report not found at {report_path}")


# UrbanSolarCarver — Run Report

*Generated 2026-04-02 15:32:50*

## Configuration

| Parameter | Value |
|-----------|-------|
| Mode | daylight |
| Voxel size | 1.0 m |
| Grid step | 1.0 m |
| Ray length | 300.0 m |
| Min altitude | 5.0° |
| Device | auto |
| Smoothing | False |
| Output format | ply |

## Preprocessing

- **Grid dimensions:** 153 × 153 × 153
- **Total voxels:** 3,581,577
- **Filled voxels:** 366,701 (10.2%)
- **Test surface sample points:** 96,441
- **Compute device:** CUDA (NVIDIA GeForce RTX 3060, 12.0 GB)
- **Score range:** [0, 32.54]
- **Score mean / median:** 4.17 / 3.608
- **Non-zero voxels:** 2,131,918 (59.5%)
- **Time:** 3.8s

## Thresholding

- **Method:** carve_fraction
- **Threshold value:** 4.327
- **Voxels kept / removed:** 1,951,622 / 1,629,955
- **Obstruction fraction carved:** 90.0%
- **Score unit:** CIE overcast sky obstruction score (dimensionless)
- **Time:** 0.5s

## Export

- **Output mesh:** `d:\RESEARCH_CENTER\ACTIVE_PROJECTS\RSBenvelope_generation\urbanSolarCarver\examples\test_outputs\daylight_demo\daylight_cie\exporting\export.ply`
- **Vertices:** 46,899
- **Triangles:** 93,844
- **Bounding box:** 151.0 × 139.0 × 31.0 m
- **Voxel retention:** 31.3%
- **Time:** 0.4s

## Total

- **Total time:** 4.7s